<img src="https://upload.wikimedia.org/wikipedia/commons/thumb/5/58/Uber_logo_2018.svg/1024px-Uber_logo_2018.svg.png" alt="UBER LOGO" width="50%" />

# UBER Pickups 

# import libraries

In [1]:
import pandas as pd
import plotly.express as px
import plotly.graph_objects as go

from sklearn.cluster import DBSCAN
from sklearn.preprocessing import StandardScaler

# Exploration via Kmeans

In [2]:
sample = pd.read_csv("data/sample.csv")
sample.shape

(100000, 8)

In [3]:
null = sample.isnull().sum()
print(f"Nombre de valeurs manquantes par colonne dans le dataset d'entrainement : {null.iloc[0]}")

Nombre de valeurs manquantes par colonne dans le dataset d'entrainement : 0


In [4]:
display(sample.head(1))

,dispatching_base_num,pickup_date,affiliated_base_num,locationid,borough,zone,lon,lat
0,b02512,2015-04-27 13:21:00,b02682,66,brooklyn,dumbo/vinegar hill,-73.9844,40.7473


In [5]:
categorical_features = ["dispatching_base_num", "affiliated_base_num", "zone", "borough"]
numerical_features = ["lat", "lon"]

In [6]:
# Preprocessing pipeline for numeric features

from sklearn.pipeline import Pipeline
from sklearn.preprocessing import StandardScaler


numeric_transformer = Pipeline(steps=[
    ("scaler", StandardScaler())
])

In [7]:
X = numeric_transformer.fit_transform(sample[numerical_features])

In [8]:
# Elbow method pour déterminer le nombre optimal de clusters pour Kmeans
from sklearn.cluster import KMeans
from sklearn.metrics import silhouette_score
inertia = []
silhouette_scores = []
K = range(2, 10)


for k in K:
    kmeans = KMeans(n_clusters=k, random_state=42)
    kmeans.fit(X)
    inertia.append(kmeans.inertia_)
    silhouette_scores.append(silhouette_score(X, kmeans.labels_))

fig_elbow = px.line(x=K, y=inertia, title="Elbow Method for KMeans", markers=True, labels={"x": "Nombre de clusters (k)", "y": "Inertie"})
fig_elbow.show()
fig_silhouette = px.line(x=K, y=silhouette_scores, title="Silhouette Scores for KMeans", markers=True, labels={"x": "Nombre de clusters (k)", "y": "Silhouette Score"})
fig_silhouette.show()

/Users/nicolasbour/miniforge3/envs/certif/lib/python3.12/site-packages/sklearn/base.py:1403: ConvergenceWarning: Number of distinct clusters (5) found smaller than n_clusters (6). Possibly due to duplicate points in X.
  return fit_method(estimator, *args, **kwargs)
/Users/nicolasbour/miniforge3/envs/certif/lib/python3.12/site-packages/sklearn/base.py:1403: ConvergenceWarning: Number of distinct clusters (5) found smaller than n_clusters (7). Possibly due to duplicate points in X.
  return fit_method(estimator, *args, **kwargs)
/Users/nicolasbour/miniforge3/envs/certif/lib/python3.12/site-packages/sklearn/base.py:1403: ConvergenceWarning: Number of distinct clusters (5) found smaller than n_clusters (8). Possibly due to duplicate points in X.
  return fit_method(estimator, *args, **kwargs)
/Users/nicolasbour/miniforge3/envs/certif/lib/python3.12/site-packages/sklearn/base.py:1403: ConvergenceWarning: Number of distinct clusters (5) found smaller than n_clusters (9). Possibly due to dup

In [9]:
X = numeric_transformer.fit_transform(sample[numerical_features])

In [10]:
kmeans = KMeans(n_clusters=4, random_state=42)
kmeans.fit(X)

sample.loc[:, "kmeans_cluster"] = kmeans.predict(X)
sample.head()

,dispatching_base_num,pickup_date,affiliated_base_num,locationid,borough,zone,lon,lat,kmeans_cluster
0,b02512,2015-04-27 13:21:00,b02682,66,brooklyn,dumbo/vinegar hill,-73.9844,40.7473,2
1,b02512,2015-04-10 19:31:00,b02617,75,manhattan,east harlem south,-73.9844,40.7473,2
2,b02512,2015-02-16 21:44:50,b02764,181,brooklyn,park slope,-73.9844,40.7473,2
3,b02512,2015-05-04 08:44:00,b02682,263,manhattan,yorkville west,-73.9844,40.7473,2
4,b02512,2015-01-14 11:39:43,b02764,161,manhattan,midtown center,-73.9844,40.7473,2


In [11]:
sample["kmeans_cluster"].value_counts()

kmeans_cluster
1    43894
0    38422
3    15768
2     1916
Name: count, dtype: int64

In [12]:
map_data = sample.copy()

map_data["lat"] = pd.to_numeric(map_data["lat"], errors="coerce")
map_data["lon"] = pd.to_numeric(map_data["lon"], errors="coerce")

map_data = map_data.dropna(subset=["lat", "lon", "kmeans_cluster", "affiliated_base_num"])

In [13]:
map_center = {
    "lat": map_data["lat"].mean(),
    "lon": map_data["lon"].mean()
}

In [14]:
cluster_colors = {
    0: "#FF6B6B",  # rouge
    1: "#19B0DE",  # bleu
    2: "#17CE48",  # vert
    3: "#F5A623",  # orange
}

fig = go.Figure()

for cluster_id, color in cluster_colors.items():
    df_cluster = map_data[map_data["kmeans_cluster"] == cluster_id]

    fig.add_trace(
        go.Densitymap(
            lat=df_cluster["lat"],
            lon=df_cluster["lon"],
            radius=15,
            opacity=0.9,
            z=[1] * len(df_cluster),
            colorscale=[[0, cluster_colors[cluster_id]], [1, cluster_colors[cluster_id]]],
            customdata=df_cluster[["kmeans_cluster", "zone", "borough", "affiliated_base_num", "lat", "lon"]].values,
            hovertemplate=(
                "Cluster: %{customdata[0]}<br>"
                "Zone: %{customdata[1]}<br>"
                "Borough: %{customdata[2]}<br>"
                "Base: %{customdata[3]}<br>"
                "Lat: %{customdata[4]:.4f}<br>"
                "Lon: %{customdata[5]:.4f}<extra></extra>"
            ),
            name=f"Cluster {cluster_id}"
        )
    )

fig.update_layout(
    map_style="carto-positron",
    map_center={
        "lat": map_data["lat"].mean(),
        "lon": map_data["lon"].mean()
    },
    map_zoom=12,
    title="Heatmap des clusters Kmeans des Pickups Uber",
    height=700,
    legend_title="Cluster"
)

fig.show()

# Db SCAN

In [15]:
Xb = sample[numerical_features]
X_scaled = StandardScaler().fit_transform(Xb)
dbscan_b = DBSCAN(eps=0.5, min_samples=90, metric="euclidean") # A 100 min sample, le 4e cluster est considéré comme du bruit
dbscan_b.fit(X_scaled)
sample["dbscan_cluster"] = dbscan_b.labels_
sample["dbscan_cluster"].value_counts()

dbscan_cluster
3    43894
1    38422
2    15768
0     1916
Name: count, dtype: int64

In [16]:
sample.head()

,dispatching_base_num,pickup_date,affiliated_base_num,locationid,borough,zone,lon,lat,kmeans_cluster,dbscan_cluster
0,b02512,2015-04-27 13:21:00,b02682,66,brooklyn,dumbo/vinegar hill,-73.9844,40.7473,2,0
1,b02512,2015-04-10 19:31:00,b02617,75,manhattan,east harlem south,-73.9844,40.7473,2,0
2,b02512,2015-02-16 21:44:50,b02764,181,brooklyn,park slope,-73.9844,40.7473,2,0
3,b02512,2015-05-04 08:44:00,b02682,263,manhattan,yorkville west,-73.9844,40.7473,2,0
4,b02512,2015-01-14 11:39:43,b02764,161,manhattan,midtown center,-73.9844,40.7473,2,0


In [17]:
map_data = sample.copy()
map_data = map_data.dropna(subset=["dbscan_cluster"])

In [19]:
cluster_colors = {
    0: "#FF6B6B",  # rouge
    1: "#19B0DE",  # bleu
    2: "#17CE48",  # vert
    3: "#9B59B6",  # violet
}

fig = go.Figure()

for cluster_id, color in cluster_colors.items():
    df_cluster = map_data[map_data["dbscan_cluster"] == cluster_id]

    fig.add_trace(
        go.Densitymap(
            lat=df_cluster["lat"],
            lon=df_cluster["lon"],
            radius=15,
            opacity=0.9,
            z=[1] * len(df_cluster),
            colorscale=[[0, cluster_colors[cluster_id]], [1, cluster_colors[cluster_id]]],
            customdata=df_cluster[["dbscan_cluster", "zone", "borough", "affiliated_base_num", "lat", "lon"]].values,
            hovertemplate=(
                "Cluster: %{customdata[0]}<br>"
                "Zone: %{customdata[1]}<br>"
                "Borough: %{customdata[2]}<br>"
                "Base: %{customdata[3]}<br>"
                "Lat: %{customdata[4]:.4f}<br>"
                "Lon: %{customdata[5]:.4f}<extra></extra>"
            ),
            name=f"Cluster {cluster_id}"
        )
    )

fig.update_layout(
    map_style="carto-positron",
    map_center={
        "lat": map_data["lat"].mean(),
        "lon": map_data["lon"].mean()
    },
    map_zoom=12,
    title="Heatmap des clusters Dbscan des Pickups Uber",
    height=700,
    legend_title="Cluster"
)

fig.show()